<a href="https://colab.research.google.com/github/Maria2007-collab/EVALUACI-N-INDIVIDUAL-2/blob/main/EV.INDIVIDUAL2.ipynb" target="_parent"><img src="https://colab.research.google.com/assets/colab-badge.svg" alt="Open In Colab"/></a>

# EXAMEN INDIVIDUAL 2
Alumna:María Saldaña Ruiz

Código:20241445


El presente trabajo tiene como objetivo realizar un análisis espacial de la ubicación de las estaciones de gasolina en Seattle, Washington, mediante el uso de herramientas de información geográfica. Para ello, se delimitará el área de estudio, se identificarán los centros educativos y las estaciones de gasolina, y se evaluará la distancia entre ambos para determinar qué estaciones cumplen con una distancia mínima de 200 metros. Finalmente, se propondrán ubicaciones alternativas para aquellas estaciones que no cumplan con este criterio, representando los resultados mediante mapas interactivos que faciliten su interpretación.

Importación de librerías

In [ ]:
!pip -q install geopandas osmnx folium mapclassify scipy

import geopandas as gpd
import pandas as pd
import numpy as np
import osmnx as ox
import folium
import requests
import matplotlib.pyplot as plt

from scipy.spatial.distance import cdist
from shapely.geometry import Point
from shapely.prepared import prep

Descarga y lectura de los sectores censales de Seattle del 2020.

In [ ]:
# URL del archivo ZIP alojado en GitHub
filez = "https://github.com/Maria2007-collab/EVALUACI-N-INDIVIDUAL-2/raw/8961c2ae16f8bf283a3d8c4dbc684d1992499dc4/2020_Census_Tracts_Seattle_8661193084158732132.zip"

# Verificar que GitHub permita descargar el archivo
respuesta = requests.get(filez)

print("Código HTTP:", respuesta.status_code)
print("Tipo de contenido:", respuesta.headers.get("Content-Type"))

if respuesta.status_code != 200:
    raise ValueError(
        "No se pudo descargar el ZIP. "
        "Debemos corregir la URL de GitHub antes de continuar."
    )

# Leer los sectores censales
seattle = gpd.read_file(filez)

# Guardar los datos con el nombre que usaremos en el análisis
tractos = seattle.copy()

# Revisar la estructura y el sistema de coordenadas
tractos.info()
print("CRS original:", tractos.crs)

Código HTTP: 200
Tipo de contenido: application/zip
<class 'geopandas.geodataframe.GeoDataFrame'>
RangeIndex: 177 entries, 0 to 176
Data columns (total 14 columns):
 #   Column      Non-Null Count  Dtype   
---  ------      --------------  -----   
 0   GEOID20     177 non-null    object  
 1   GROSS_ACRE  177 non-null    float64 
 2   LAND_ACRES  177 non-null    float64 
 3   WATER_ACRE  177 non-null    float64 
 4   NAME        177 non-null    object  
 5   TRACT_NUMB  177 non-null    int64   
 6   BASENAME    177 non-null    object  
 7   UVDA_AREA   177 non-null    object  
 8   CRA_NO      177 non-null    float64 
 9   CRA_GRP     177 non-null    int32   
 10  GEN_ALIAS   177 non-null    object  
 11  DETL_NAMES  177 non-null    object  
 12  C_DISTRICT  177 non-null    int64   
 13  geometry    177 non-null    geometry
dtypes: float64(4), geometry(1), int32(1), int64(2), object(6)
memory usage: 18.8+ KB
CRS original: PROJCS["NAD83(HARN) / Washington North (ftUS)",GEOGCS["NAD83(HA

In [ ]:
# Obtener el límite de Seattle desde OpenStreetMap
ciudad = ox.geocode_to_gdf("Seattle, Washington, USA")

# Transformar a UTM zona 10N para trabajar en metros
ciudad = ciudad.to_crs(epsg=32610)

# Disolver para obtener un solo polígono municipal
ciudad = ciudad[["geometry"]].dissolve()

# Guardar la geometría del límite
limite_seattle = ciudad.geometry.iloc[0]

# Visualizar el límite municipal
ciudad.explore(
    tiles="CartoDB positron",
    color="black",
    style_kwds={"fillOpacity": 0.1}
)

/usr/local/lib/python3.13/dist-packages/geopandas/explore.py:383: UserWarning: CartoDB tiles now require an API key. Please provide one to continue using the tiles. You can request the key at https://carto.com/basemaps/apikey/.
  tiles = tiles.build_url(scale_factor="{r}")


Corregí geometrías inválidas y comprobé que los datos tenían sistema de coordenadas. Cambiamos la de reproyección a UTM. Y trabajamos con la proyección adecuada para seattle.

In [ ]:
# Corregir geometrías inválidas
tractos["geometry"] = tractos.geometry.make_valid()

# Comprobar que los datos tengan sistema de coordenadas
if tractos.crs is None:
    raise ValueError("Los sectores censales no tienen CRS definido.")

# Transformar a UTM zona 10N
# Esta proyección es adecuada para calcular distancias en metros en Seattle
tractos_utm = tractos.to_crs(epsg=32610)

# Recortar los sectores censales al límite municipal
tractos_seattle = gpd.clip(tractos_utm, ciudad)

# Unir los polígonos en un solo límite
seattle = tractos_seattle[["geometry"]].dissolve()

# Mostrar el mapa
seattle.explore(
    tiles="CartoDB positron",
    color="black",
    style_kwds={"fillOpacity": 0.1}
)

/usr/local/lib/python3.13/dist-packages/geopandas/explore.py:383: UserWarning: CartoDB tiles now require an API key. Please provide one to continue using the tiles. You can request the key at https://carto.com/basemaps/apikey/.
  tiles = tiles.build_url(scale_factor="{r}")


Bucamos colegios, universidades, institutos y jardines infantiles, también transformamos a UTM. Y obtenemos el número de centros educativos.


In [ ]:
# Buscar colegios, universidades, institutos y jardines infantiles
tags_educacion = {
    "amenity": [
        "school",
        "university",
        "college",
        "kindergarten"
    ]
}

educacion = ox.features_from_place(
    "Seattle, Washington, USA",
    tags=tags_educacion
)

# Eliminar registros sin geometría
educacion = educacion[
    educacion.geometry.notna()
].copy()

# Transformar a UTM zona 10N
educacion = educacion.to_crs(epsg=32610)

# Convertir cada geometría en un punto representativo
educacion["geometry"] = (
    educacion.geometry.representative_point()
)

# Conservar centros dentro del límite municipal
educacion = educacion[
    educacion.geometry.within(limite_seattle)
].copy()

print("Centros educativos:", len(educacion))

Centros educativos: 297


In [ ]:
# Buscar estaciones de combustible en OpenStreetMap
gasolineras = ox.features_from_place(
    "Seattle, Washington, USA",
    tags={"amenity": "fuel"}
)

# Eliminar geometrías vacías
gasolineras = gasolineras[
    gasolineras.geometry.notna()
].copy()

# Transformar a UTM zona 10N
gasolineras = gasolineras.to_crs(epsg=32610)

# Representar cada estación mediante un punto
gasolineras["geometry"] = (
    gasolineras.geometry.representative_point()
)

# Conservar las estaciones dentro de Seattle
gasolineras = gasolineras[
    gasolineras.geometry.within(limite_seattle)
].copy()

# Crear un identificador
gasolineras = gasolineras.reset_index(drop=True)
gasolineras["id_gasolinera"] = gasolineras.index + 1

print("Gasolineras:", len(gasolineras))

Gasolineras: 128


Creación de mapas

In [ ]:
# Crear el mapa base
mapa = seattle.explore(
    tiles="CartoDB positron",
    color="black",
    style_kwds={"fillOpacity": 0.1},
    name="Límite de Seattle"
)

# Añadir centros educativos
educacion.explore(
    m=mapa,
    color="blue",
    marker_type="circle",
    marker_kwds={"radius": 3},
    name="Centros educativos"
)

# Añadir gasolineras
gasolineras.explore(
    m=mapa,
    color="orange",
    marker_type="marker",
    name="Gasolineras"
)

folium.LayerControl().add_to(mapa)
mapa

/usr/local/lib/python3.13/dist-packages/geopandas/explore.py:383: UserWarning: CartoDB tiles now require an API key. Please provide one to continue using the tiles. You can request the key at https://carto.com/basemaps/apikey/.
  tiles = tiles.build_url(scale_factor="{r}")


In [ ]:
# Obtener coordenadas de gasolineras y centros educativos
coords_gas = np.array([
    (p.x, p.y) for p in gasolineras.geometry
])

coords_edu = np.array([
    (p.x, p.y) for p in educacion.geometry
])

# Calcular la matriz de distancias en metros
D_Matrix_fuel_school = cdist(coords_gas, coords_edu)

# Distancia mínima de cada gasolinera a cualquier centro educativo
gasolineras["dist_educacion_m"] = (
    D_Matrix_fuel_school.min(axis=1)
)

# Clasificar con el umbral de 200 metros
gasolineras["clasificacion"] = np.where(
    gasolineras["dist_educacion_m"] < 200,
    "Mal ubicada",
    "Bien ubicada"
)

gasolineras[
    ["id_gasolinera", "dist_educacion_m", "clasificacion"]
].head(10)

,id_gasolinera,dist_educacion_m,clasificacion
0,1,91.839240,Mal ubicada
1,2,75.072216,Mal ubicada
2,3,859.819564,Bien ubicada
3,4,179.219722,Mal ubicada
4,5,260.547583,Bien ubicada
5,6,279.001615,Bien ubicada
6,7,420.322212,Bien ubicada
7,8,944.764589,Bien ubicada
8,9,521.597378,Bien ubicada
9,10,553.486995,Bien ubicada


In [ ]:
print(gasolineras["clasificacion"].value_counts())

bien_ubicadas = gasolineras[
    gasolineras["clasificacion"] == "Bien ubicada"
].copy()

mal_ubicadas = gasolineras[
    gasolineras["clasificacion"] == "Mal ubicada"
].copy()

print("Bien ubicadas:", len(bien_ubicadas))
print("Mal ubicadas:", len(mal_ubicadas))

clasificacion
Bien ubicada    101
Mal ubicada      27
Name: count, dtype: int64
Bien ubicadas: 101
Mal ubicadas: 27


In [ ]:
# Generar zonas de protección alrededor de los centros educativos
buffer_educacion = educacion[["geometry"]].copy()
buffer_educacion["geometry"] = (
    buffer_educacion.geometry.buffer(200)
)

# Unir los buffers superpuestos
zonas_200m = buffer_educacion.dissolve()

# Mostrar las zonas de 200 metros
mapa_200m = seattle.explore(
    tiles="CartoDB positron",
    color="black",
    style_kwds={"fillOpacity": 0.05},
    name="Seattle"
)

zonas_200m.explore(
    m=mapa_200m,
    color="red",
    style_kwds={"fillOpacity": 0.2},
    name="Zonas de 200 m"
)

educacion.explore(
    m=mapa_200m,
    color="blue",
    marker_type="circle",
    marker_kwds={"radius": 3},
    name="Centros educativos"
)

gasolineras.explore(
    m=mapa_200m,
    color="orange",
    marker_type="marker",
    name="Gasolineras"
)

folium.LayerControl().add_to(mapa_200m)
mapa_200m

/usr/local/lib/python3.13/dist-packages/geopandas/explore.py:383: UserWarning: CartoDB tiles now require an API key. Please provide one to continue using the tiles. You can request the key at https://carto.com/basemaps/apikey/.
  tiles = tiles.build_url(scale_factor="{r}")


In [ ]:
# Obtener los límites del área de Seattle
minx, miny, maxx, maxy = ciudad.total_bounds

# Crear una cuadrícula de puntos cada 100 metros
paso = 100

x_coords = np.arange(minx, maxx, paso)
y_coords = np.arange(miny, maxy, paso)

# Preparar el polígono para comprobar si un punto está dentro
poligono_preparado = prep(limite_seattle)

puntos_candidatos = [
    Point(x, y)
    for x in x_coords
    for y in y_coords
    if poligono_preparado.contains(Point(x, y))
]

candidatos = gpd.GeoDataFrame(
    geometry=puntos_candidatos,
    crs="EPSG:32610"
)

# Excluir puntos a menos de 200 metros de cualquier centro educativo
coords_candidatos = np.array([
    (p.x, p.y) for p in candidatos.geometry
])

dist_candidatos_edu = cdist(
    coords_candidatos,
    coords_edu
)

candidatos = candidatos[
    dist_candidatos_edu.min(axis=1) >= 200
].copy()

# Excluir candidatos a menos de 100 metros de una gasolinera existente
coords_candidatos = np.array([
    (p.x, p.y) for p in candidatos.geometry
])

dist_candidatos_gas = cdist(
    coords_candidatos,
    coords_gas
)

candidatos = candidatos[
    dist_candidatos_gas.min(axis=1) >= 100
].copy()

print("Candidatos disponibles:", len(candidatos))

Candidatos disponibles: 33869


In [ ]:
# Guardar las propuestas
propuestas = []

# Evitar asignar el mismo candidato a más de una estación
candidatos_disponibles = candidatos.copy()

# Buscar una ubicación alternativa para cada gasolinera mal ubicada
for _, estacion in mal_ubicadas.iterrows():

    if candidatos_disponibles.empty:
        print("No quedan candidatos disponibles.")
        break

    # Distancia entre la estación actual y los candidatos
    distancias = candidatos_disponibles.geometry.distance(
        estacion.geometry
    )

    # Elegir el candidato más cercano
    indice_candidato = distancias.idxmin()
    punto_propuesto = candidatos_disponibles.loc[
        indice_candidato, "geometry"
    ]

    propuestas.append({
        "id_gasolinera": estacion["id_gasolinera"],
        "distancia_traslado_m": estacion.geometry.distance(
            punto_propuesto
        ),
        "geometry": punto_propuesto
    })

    # Retirar el punto elegido
    candidatos_disponibles = candidatos_disponibles.drop(
        index=indice_candidato
    )

reubicaciones = gpd.GeoDataFrame(
    propuestas,
    geometry="geometry",
    crs="EPSG:32610"
)

reubicaciones.head()

,id_gasolinera,distancia_traslado_m,geometry
0,1,206.859657,POINT (545056.878 5276188.635)
1,2,258.494505,POINT (551256.878 5274688.635)
2,4,150.419228,POINT (550556.878 5269888.635)
3,12,124.220113,POINT (546756.878 5279788.635)
4,15,104.848721,POINT (548256.878 5263488.635)


In [ ]:
if not reubicaciones.empty:

    coords_prop = np.array([
        (p.x, p.y) for p in reubicaciones.geometry
    ])

    # Calcular la distancia a todos los centros educativos
    D_Matrix_propuestas = cdist(
        coords_prop,
        coords_edu
    )

    reubicaciones["dist_educacion_m"] = (
        D_Matrix_propuestas.min(axis=1)
    )

    reubicaciones["cumple_200m"] = (
        reubicaciones["dist_educacion_m"] >= 200
    )

    display(reubicaciones[
        [
            "id_gasolinera",
            "distancia_traslado_m",
            "dist_educacion_m",
            "cumple_200m"
        ]
    ])

else:
    print("No se encontraron ubicaciones alternativas.")

,id_gasolinera,distancia_traslado_m,dist_educacion_m,cumple_200m
0,1,206.859657,294.107204,True
1,2,258.494505,230.857214,True
2,4,150.419228,269.207622,True
3,12,124.220113,204.010937,True
4,15,104.848721,258.269340,True
5,16,166.854920,215.017854,True
6,20,142.441196,270.456716,True
7,26,130.431271,322.154349,True
8,31,145.419797,238.759996,True
9,33,154.391498,268.973718,True


In [ ]:
# Crear el mapa base
mapa_final = seattle.explore(
    tiles="CartoDB positron",
    color="black",
    style_kwds={"fillOpacity": 0.05},
    name="Límite de Seattle"
)

# Añadir centros educativos
educacion.explore(
    m=mapa_final,
    color="blue",
    marker_type="circle",
    marker_kwds={"radius": 3},
    name="Centros educativos"
)

# Añadir gasolineras que cumplen el criterio
bien_ubicadas.explore(
    m=mapa_final,
    color="green",
    marker_type="marker",
    tooltip=["id_gasolinera", "dist_educacion_m"],
    name="Bien ubicadas"
)

# Añadir gasolineras que requieren reubicación
mal_ubicadas.explore(
    m=mapa_final,
    color="red",
    marker_type="marker",
    tooltip=["id_gasolinera", "dist_educacion_m"],
    name="Mal ubicadas"
)

# Añadir ubicaciones propuestas
if not reubicaciones.empty:
    reubicaciones.explore(
        m=mapa_final,
        color="purple",
        marker_type="marker",
        tooltip=[
            "id_gasolinera",
            "distancia_traslado_m",
            "dist_educacion_m"
        ],
        name="Ubicaciones propuestas"
    )

folium.LayerControl().add_to(mapa_final)
mapa_final

/usr/local/lib/python3.13/dist-packages/geopandas/explore.py:383: UserWarning: CartoDB tiles now require an API key. Please provide one to continue using the tiles. You can request the key at https://carto.com/basemaps/apikey/.
  tiles = tiles.build_url(scale_factor="{r}")


In [ ]:
resumen = pd.DataFrame({
    "Indicador": [
        "Centros educativos",
        "Gasolineras",
        "Gasolineras bien ubicadas",
        "Gasolineras mal ubicadas",
        "Ubicaciones propuestas"
    ],
    "Cantidad": [
        len(educacion),
        len(gasolineras),
        len(bien_ubicadas),
        len(mal_ubicadas),
        len(reubicaciones)
    ]
})

display(resumen)

,Indicador,Cantidad
0,Centros educativos,297
1,Gasolineras,128
2,Gasolineras bien ubicadas,101
3,Gasolineras mal ubicadas,27
4,Ubicaciones propuestas,27
